In [45]:
import nltk

# List of packages to download
packages = ['punkt', 'punkt_tab', 'wordnet', 'omw-1.4']

for package in packages:
    nltk.download(package)

[nltk_data] Downloading package punkt to /root/nltk_data...
[nltk_data]   Package punkt is already up-to-date!
[nltk_data] Downloading package punkt_tab to /root/nltk_data...
[nltk_data]   Package punkt_tab is already up-to-date!
[nltk_data] Downloading package wordnet to /root/nltk_data...
[nltk_data]   Package wordnet is already up-to-date!
[nltk_data] Downloading package omw-1.4 to /root/nltk_data...
[nltk_data]   Package omw-1.4 is already up-to-date!


In [46]:
from nltk.tokenize import word_tokenize
from nltk.stem import PorterStemmer,WordNetLemmatizer
from sklearn.feature_extraction.text import CountVectorizer,TfidfVectorizer

In [47]:
from google.colab import drive
drive.mount('/content/drive')

Drive already mounted at /content/drive; to attempt to forcibly remount, call drive.mount("/content/drive", force_remount=True).


In [48]:
import pandas as pd

path = "/content/drive/MyDrive/dataset/twitter.csv"
df=pd.read_csv(path,header=None,names=['tweet_id','entity','sentiment','text'])

df.head()

,tweet_id,entity,sentiment,text
0,2401,Borderlands,Positive,im getting on borderlands and i will murder yo...
1,2401,Borderlands,Positive,I am coming to the borders and I will kill you...
2,2401,Borderlands,Positive,im getting on borderlands and i will kill you ...
3,2401,Borderlands,Positive,im coming on borderlands and i will murder you...
4,2401,Borderlands,Positive,im getting on borderlands 2 and i will murder ...


In [49]:
df.shape

(74682, 4)

In [50]:
df.info()

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 74682 entries, 0 to 74681
Data columns (total 4 columns):
 #   Column     Non-Null Count  Dtype 
---  ------     --------------  ----- 
 0   tweet_id   74682 non-null  int64 
 1   entity     74682 non-null  object
 2   sentiment  74682 non-null  object
 3   text       73996 non-null  object
dtypes: int64(1), object(3)
memory usage: 2.3+ MB


In [51]:
df.isna().sum()

,0
tweet_id,0
entity,0
sentiment,0
text,686


In [52]:
#Drop rows where 'text' is NaN
df.dropna(subset=['text'],inplace=True)

In [53]:
df.isnull().sum()

,0
tweet_id,0
entity,0
sentiment,0
text,0


In [54]:
# Reset the index (good practice after dropping rows)
df.reset_index(drop=True,inplace=True)

In [55]:
df.describe

<bound method NDFrame.describe of        tweet_id       entity sentiment  \
0          2401  Borderlands  Positive   
1          2401  Borderlands  Positive   
2          2401  Borderlands  Positive   
3          2401  Borderlands  Positive   
4          2401  Borderlands  Positive   
...         ...          ...       ...   
73991      9200       Nvidia  Positive   
73992      9200       Nvidia  Positive   
73993      9200       Nvidia  Positive   
73994      9200       Nvidia  Positive   
73995      9200       Nvidia  Positive   

                                                    text  
0      im getting on borderlands and i will murder yo...  
1      I am coming to the borders and I will kill you...  
2      im getting on borderlands and i will kill you ...  
3      im coming on borderlands and i will murder you...  
4      im getting on borderlands 2 and i will murder ...  
...                                                  ...  
73991  Just realized that the Windows partition of my...  
73992  Just realized that my Mac window partition is ...  
73993  Just realized the windows partition of my Mac ...  
73994  Just realized between the windows partition of...  
73995  Just like the windows partition of my Mac is l...  

[73996 rows x 4 columns]>

In [56]:
df.columns

Index(['tweet_id', 'entity', 'sentiment', 'text'], dtype='object')

In [57]:
df["sentiment"].value_counts()

,count
sentiment,
Negative,22358
Positive,20655
Neutral,18108
Irrelevant,12875


In [58]:
df["text"] = df["text"].str.lower()

In [59]:
import re
def clean_text(text):
    text=re.sub(r"https?://\S+|www\.\S+"," ",text)
    text=re.sub(r"@\w+"," ",text)
    text=re.sub(r"#"," ",text)
    text=re.sub(r"&\w+"," ",text)
    text=re.sub(r"\d+"," ",text)
    text=re.sub(r"\s+"," ",text).strip()

    return text

In [60]:
df["text"]=df["text"].apply(clean_text)

In [61]:
df.head()

,tweet_id,entity,sentiment,text
0,2401,Borderlands,Positive,im getting on borderlands and i will murder yo...
1,2401,Borderlands,Positive,i am coming to the borders and i will kill you...
2,2401,Borderlands,Positive,im getting on borderlands and i will kill you ...
3,2401,Borderlands,Positive,im coming on borderlands and i will murder you...
4,2401,Borderlands,Positive,im getting on borderlands and i will murder yo...


In [62]:
df['text']

,text
0,im getting on borderlands and i will murder yo...
1,i am coming to the borders and i will kill you...
2,im getting on borderlands and i will kill you ...
3,im coming on borderlands and i will murder you...
4,im getting on borderlands and i will murder yo...
...,...
73991,just realized that the windows partition of my...
73992,just realized that my mac window partition is ...
73993,just realized the windows partition of my mac ...
73994,just realized between the windows partition of...


In [63]:
df["tokens"]=df["text"].apply(word_tokenize)

In [64]:
df

,tweet_id,entity,sentiment,text,tokens
0,2401,Borderlands,Positive,im getting on borderlands and i will murder yo...,"[im, getting, on, borderlands, and, i, will, m..."
1,2401,Borderlands,Positive,i am coming to the borders and i will kill you...,"[i, am, coming, to, the, borders, and, i, will..."
2,2401,Borderlands,Positive,im getting on borderlands and i will kill you ...,"[im, getting, on, borderlands, and, i, will, k..."
3,2401,Borderlands,Positive,im coming on borderlands and i will murder you...,"[im, coming, on, borderlands, and, i, will, mu..."
4,2401,Borderlands,Positive,im getting on borderlands and i will murder yo...,"[im, getting, on, borderlands, and, i, will, m..."
...,...,...,...,...,...
73991,9200,Nvidia,Positive,just realized that the windows partition of my...,"[just, realized, that, the, windows, partition..."
73992,9200,Nvidia,Positive,just realized that my mac window partition is ...,"[just, realized, that, my, mac, window, partit..."
73993,9200,Nvidia,Positive,just realized the windows partition of my mac ...,"[just, realized, the, windows, partition, of, ..."
73994,9200,Nvidia,Positive,just realized between the windows partition of...,"[just, realized, between, the, windows, partit..."


In [65]:
stemmer = PorterStemmer()
df['tokens'] = df['tokens'].apply(lambda toks: [stemmer.stem(t) for t in toks])
df

,tweet_id,entity,sentiment,text,tokens
0,2401,Borderlands,Positive,im getting on borderlands and i will murder yo...,"[im, get, on, borderland, and, i, will, murder..."
1,2401,Borderlands,Positive,i am coming to the borders and i will kill you...,"[i, am, come, to, the, border, and, i, will, k..."
2,2401,Borderlands,Positive,im getting on borderlands and i will kill you ...,"[im, get, on, borderland, and, i, will, kill, ..."
3,2401,Borderlands,Positive,im coming on borderlands and i will murder you...,"[im, come, on, borderland, and, i, will, murde..."
4,2401,Borderlands,Positive,im getting on borderlands and i will murder yo...,"[im, get, on, borderland, and, i, will, murder..."
...,...,...,...,...,...
73991,9200,Nvidia,Positive,just realized that the windows partition of my...,"[just, realiz, that, the, window, partit, of, ..."
73992,9200,Nvidia,Positive,just realized that my mac window partition is ...,"[just, realiz, that, my, mac, window, partit, ..."
73993,9200,Nvidia,Positive,just realized the windows partition of my mac ...,"[just, realiz, the, window, partit, of, my, ma..."
73994,9200,Nvidia,Positive,just realized between the windows partition of...,"[just, realiz, between, the, window, partit, o..."


In [66]:
lemmatizer= WordNetLemmatizer()

# Lemmatize each token
df["tokens"]=df["tokens"].apply(lambda toks: [lemmatizer.lemmatize(t) for t in toks])

# Join the tokens back into a sentence
df['tokens'] = df["tokens"].apply(' '.join)
df

,tweet_id,entity,sentiment,text,tokens
0,2401,Borderlands,Positive,im getting on borderlands and i will murder yo...,"im get on borderland and i will murder you all ,"
1,2401,Borderlands,Positive,i am coming to the borders and i will kill you...,"i am come to the border and i will kill you all ,"
2,2401,Borderlands,Positive,im getting on borderlands and i will kill you ...,"im get on borderland and i will kill you all ,"
3,2401,Borderlands,Positive,im coming on borderlands and i will murder you...,"im come on borderland and i will murder you all ,"
4,2401,Borderlands,Positive,im getting on borderlands and i will murder yo...,im get on borderland and i will murder you me ...
...,...,...,...,...,...
73991,9200,Nvidia,Positive,just realized that the windows partition of my...,just realiz that the window partit of my mac i...
73992,9200,Nvidia,Positive,just realized that my mac window partition is ...,just realiz that my mac window partit is year ...
73993,9200,Nvidia,Positive,just realized the windows partition of my mac ...,just realiz the window partit of my mac is now...
73994,9200,Nvidia,Positive,just realized between the windows partition of...,just realiz between the window partit of my ma...


In [67]:
tfidf=TfidfVectorizer(max_features=5000)
X_tfidf=tfidf.fit_transform(df["tokens"])

In [68]:
X_tfidf

<Compressed Sparse Row sparse matrix of dtype 'float64'
	with 1090916 stored elements and shape (73996, 5000)>

In [69]:
df["sentiment"].value_counts()

,count
sentiment,
Negative,22358
Positive,20655
Neutral,18108
Irrelevant,12875


In [70]:
from sklearn.preprocessing import LabelEncoder

label_eoncoder=LabelEncoder()
y_encoded=label_eoncoder.fit_transform(df["sentiment"])
print(label_eoncoder.classes_)

['Irrelevant' 'Negative' 'Neutral' 'Positive']


In [71]:
num_class=len(label_eoncoder.classes_)
print(num_class)

4


In [72]:
df["tokens"]

,tokens
0,"im get on borderland and i will murder you all ,"
1,"i am come to the border and i will kill you all ,"
2,"im get on borderland and i will kill you all ,"
3,"im come on borderland and i will murder you all ,"
4,im get on borderland and i will murder you me ...
...,...
73991,just realiz that the window partit of my mac i...
73992,just realiz that my mac window partit is year ...
73993,just realiz the window partit of my mac is now...
73994,just realiz between the window partit of my ma...


In [73]:
all_words=" ".join(df["tokens"]).split()
print(all_words)

['im', 'get', 'on', 'borderland', 'and', 'i', 'will', 'murder', 'you', 'all', ',', 'i', 'am', 'come', 'to', 'the', 'border', 'and', 'i', 'will', 'kill', 'you', 'all', ',', 'im', 'get', 'on', 'borderland', 'and', 'i', 'will', 'kill', 'you', 'all', ',', 'im', 'come', 'on', 'borderland', 'and', 'i', 'will', 'murder', 'you', 'all', ',', 'im', 'get', 'on', 'borderland', 'and', 'i', 'will', 'murder', 'you', 'me', 'all', ',', 'im', 'get', 'into', 'borderland', 'and', 'i', 'can', 'murder', 'you', 'all', ',', 'so', 'i', 'spent', 'a', 'few', 'hour', 'make', 'someth', 'for', 'fun', '.', '.', '.', 'if', 'you', 'do', "n't", 'know', 'i', 'am', 'a', 'huge', 'fan', 'and', 'maya', 'is', 'one', 'of', 'my', 'favorit', 'charact', '.', 'so', 'i', 'decid', 'to', 'make', 'myself', 'a', 'wallpap', 'for', 'my', 'pc', '.', '.', 'here', 'is', 'the', 'origin', 'imag', 'versu', 'the', 'creation', 'i', 'made', ':', ')', 'enjoy', '!', 'pic.twitter.com/mlsi', 'wf', 'jg', 'so', 'i', 'spent', 'a', 'coupl', 'of', 'hour'

In [74]:
unique_words = sorted(list(set(all_words)))
print(unique_words)

['!', '$', '%', '&', "'", "''", "'-", "'-microsoft", "'a", "'abbassador", "'about", "'ai", "'all", "'amaz", "'and", "'antebellum", "'anti-astrolog", "'apex", "'are", "'assassin", "'at", "'ball", "'bi", "'bout", "'but", "'call", "'care", "'cncnx", "'covid-", "'crypto", "'cyberpunk", "'d", "'danger", "'did", "'disney", "'douglif", "'drug", "'eli", "'em", "'excel", "'fact", "'fascism", "'fee", "'fee'sect", "'ff", "'for", "'fornit", "'fortnit", "'get", "'gob", "'god", "'greed", "'gud", "'hear", "'hearthston", "'here", "'i", "'immedi", "'in", "'intern", "'it", "'jamesharl", "'kama", "'kobeee", "'leagu", "'left", "'lightn", "'ll", "'m", "'man", "'marvel", "'mi", "'most", "'n", "'new", "'not", "'now", "'nuff", "'ol", "'on", "'oop", "'or", "'over", "'overrun", "'parti", "'peenois", "'peopl", "'preset", "'punk", "'queen", "'re", "'real", "'red", "'rip", "'s", "'score", "'sold", "'speed", "'spoof", "'standard", "'stop", "'summer", "'surgeon", "'t", "'technolog", "'temporari", "'that", "'the", "'

In [75]:
vocab={word:i+1 for i, word in enumerate(unique_words)}
vocab_size=len(vocab)+1
print(vocab_size)

30756


In [76]:
print(vocab)

{'!': 1, '$': 2, '%': 3, '&': 4, "'": 5, "''": 6, "'-": 7, "'-microsoft": 8, "'a": 9, "'abbassador": 10, "'about": 11, "'ai": 12, "'all": 13, "'amaz": 14, "'and": 15, "'antebellum": 16, "'anti-astrolog": 17, "'apex": 18, "'are": 19, "'assassin": 20, "'at": 21, "'ball": 22, "'bi": 23, "'bout": 24, "'but": 25, "'call": 26, "'care": 27, "'cncnx": 28, "'covid-": 29, "'crypto": 30, "'cyberpunk": 31, "'d": 32, "'danger": 33, "'did": 34, "'disney": 35, "'douglif": 36, "'drug": 37, "'eli": 38, "'em": 39, "'excel": 40, "'fact": 41, "'fascism": 42, "'fee": 43, "'fee'sect": 44, "'ff": 45, "'for": 46, "'fornit": 47, "'fortnit": 48, "'get": 49, "'gob": 50, "'god": 51, "'greed": 52, "'gud": 53, "'hear": 54, "'hearthston": 55, "'here": 56, "'i": 57, "'immedi": 58, "'in": 59, "'intern": 60, "'it": 61, "'jamesharl": 62, "'kama": 63, "'kobeee": 64, "'leagu": 65, "'left": 66, "'lightn": 67, "'ll": 68, "'m": 69, "'man": 70, "'marvel": 71, "'mi": 72, "'most": 73, "'n": 74, "'new": 75, "'not": 76, "'now": 7

In [77]:
X_sequences=[]
for sentence in df["tokens"]: #to remove duplicate value
    seq=[vocab[word] for word in sentence.split() if word in vocab]
    X_sequences.append(seq)

In [78]:
for i , seq in enumerate(X_sequences):
    print(seq) #vocab id

Streaming output truncated to the last 5000 lines.
[25407, 3072, 349]
[349, 830, 27355, 841, 349]
[349, 29833, 3072, 349]
[349, 16433, 349]
[25665, 14929, 13953, 5036, 1]
[25665, 14929, 23823, 5036, 1]
[13010, 14929, 23748, 5036, 1]
[25665, 14929, 13953, 3697, 1]
[25665, 14929, 351, 13953, 5036, 1]
[25665, 14929, 20316, 5036, 1]
[14929, 9457, 25969]
[14929, 9457, 25969, 13010]
[14929, 9457, 830, 27355, 841]
[14929, 9457, 1106, 25969]
[14929, 9457, 1718]
[25591, 95, 18052, 26946, 18299, 9365, 6132, 350, 349, 7869, 13010, 10261, 6559, 18663, 143, 8354, 12959, 22360, 1718, 25407, 29134, 4084, 350, 349, 18156, 13010, 10261, 21487, 143, 13010, 95, 2641, 143, 8354, 12959, 22360, 1718, 25407, 29134, 4084, 349]
[25591, 2055, 18052, 26946, 18299, 9365, 6132, 351, 7869, 13010, 12959, 6559, 3122, 143, 8354, 12959, 22360, 1718, 25407, 29134, 12959, 4084, 351, 18156, 13010, 12959, 20582, 143, 13010, 12959, 2641, 143, 8354, 12959, 22360, 1718, 25407, 29134, 12959, 4084, 349]
[25591, 2055, 18052, 269

In [79]:
import numpy as np

max_len=100
x_padded=np.zeros((len(X_sequences),max_len),dtype=np.int32)
print(x_padded)

[[0 0 0 ... 0 0 0]
 [0 0 0 ... 0 0 0]
 [0 0 0 ... 0 0 0]
 ...
 [0 0 0 ... 0 0 0]
 [0 0 0 ... 0 0 0]
 [0 0 0 ... 0 0 0]]


In [80]:
for i, seq in enumerate(X_sequences):
    if len(seq) > 0:
        x_padded[i, : len(seq[:max_len])] = seq[:max_len]

In [81]:
print(x_padded)

[[12429 10261 17966 ...     0     0     0]
 [12191  1549  5350 ...     0     0     0]
 [12429 10261 17966 ...     0     0     0]
 ...
 [13633 21222 25407 ...     0     0     0]
 [13633 21222  3114 ...     0     0     0]
 [13633 14639 25407 ...     0     0     0]]


In [82]:
from sklearn.model_selection import train_test_split

x_train,x_test,y_train,y_test=train_test_split(x_padded,y_encoded,test_size=0.2,random_state=42,stratify=y_encoded)
print(x_train)

[[26098 12959  4347 ...     0     0     0]
 [ 1718 28461 12959 ...     0     0     0]
 [12959  8581 14965 ...     0     0     0]
 ...
 [25380 28340   887 ...     0     0     0]
 [  133 14423   134 ...     0     0     0]
 [24900 21798 21798 ...     0     0     0]]


In [83]:
import torch
from torch.utils.data import DataLoader,TensorDataset

train_dataset=TensorDataset(torch.tensor(x_train,dtype=torch.long),torch.tensor(y_train,dtype=torch.long))

test_dataset=TensorDataset(torch.tensor(x_test,dtype=torch.long),torch.tensor(y_test,dtype=torch.long))

In [84]:
batch_size=64
train_loader=DataLoader(train_dataset,batch_size=batch_size,shuffle=True)
test_loader=DataLoader(test_dataset,batch_size=batch_size,shuffle=False)

In [85]:
device=torch.device("cuda" if torch.cuda.is_available() else"cpu")
print(f"using device: {device}")

using device: cuda


In [86]:
import torch
import torch.nn as nn
from torch.nn.utils.rnn import pack_padded_sequence

class SimpleRNN(nn.Module):
    def __init__(self, vocab_size, embedding_dim, hidden_dim, output_dim):
        super().__init__()

        self.embedding = nn.Embedding(
            vocab_size,
            embedding_dim,
            padding_idx=0
        )

        self.rnn = nn.RNN(
            embedding_dim,
            hidden_dim,
            batch_first=True
        )

        self.fc = nn.Linear(hidden_dim, output_dim)

    def forward(self, text):

        # 1. Count the real words in each tweet
        lengths = text.ne(0).sum(dim=1).clamp(min=1)

        # 2. Convert token IDs into embeddings
        embedded = self.embedding(text)

        # 3. Ignore padding positions during RNN processing
        packed = pack_padded_sequence(
            embedded,
            lengths.cpu(),
            batch_first=True,
            enforce_sorted=False
        )

        # 4. Process the actual sequence
        _, hidden = self.rnn(packed)

        # 5. Use the final hidden state for classification
        final_hidden = hidden[-1]

        # 6. Produce scores for the four sentiment classes
        return self.fc(final_hidden)

In [87]:
EMBEDDING_DIM=100
HIDDEN_DIM=128
OUTPUT_DIM=4

model=SimpleRNN(vocab_size,EMBEDDING_DIM,HIDDEN_DIM,OUTPUT_DIM).to(device)
print(model)

criterion=nn.CrossEntropyLoss()

optimizer = torch.optim.Adam(
    model.parameters(),
    lr=0.001
)

SimpleRNN(
  (embedding): Embedding(30756, 100, padding_idx=0)
  (rnn): RNN(100, 128, batch_first=True)
  (fc): Linear(in_features=128, out_features=4, bias=True)
)


In [88]:
epochs=25

for epoch in range(epochs):
    model.train()

    epoch_loss = 0
    correct = 0
    total = 0

    for texts,labels in train_loader:
        texts,labels=texts.to(device),labels.to(device)

        optimizer.zero_grad()
        predictions=model(texts)
        loss=criterion(predictions,labels)

        loss.backward()
        optimizer.step()

        epoch_loss +=loss.item()
        _,predicted=torch.max(predictions.data,1)
        total+=labels.size(0)
        correct+=(predicted==labels).sum().item()

    accuracy=100*correct/total
    print(f"Epoch {epoch+1:02d}/{epochs:02d} | Loss:{epoch_loss/len(train_loader):.4f} | Train Accuracy:{accuracy:.2f}%")

Epoch 01/25 | Loss:1.2310 | Train Accuracy:45.62%
Epoch 02/25 | Loss:1.0177 | Train Accuracy:58.86%
Epoch 03/25 | Loss:0.8219 | Train Accuracy:68.24%
Epoch 04/25 | Loss:0.6567 | Train Accuracy:75.34%
Epoch 05/25 | Loss:0.5150 | Train Accuracy:81.11%
Epoch 06/25 | Loss:0.4050 | Train Accuracy:85.32%
Epoch 07/25 | Loss:0.3351 | Train Accuracy:87.91%
Epoch 08/25 | Loss:0.2624 | Train Accuracy:90.62%
Epoch 09/25 | Loss:0.2179 | Train Accuracy:92.19%
Epoch 10/25 | Loss:0.2205 | Train Accuracy:92.18%
Epoch 11/25 | Loss:0.2029 | Train Accuracy:92.61%
Epoch 12/25 | Loss:0.1290 | Train Accuracy:95.38%
Epoch 13/25 | Loss:0.1226 | Train Accuracy:95.56%
Epoch 14/25 | Loss:0.1411 | Train Accuracy:94.84%
Epoch 15/25 | Loss:0.1053 | Train Accuracy:96.11%
Epoch 16/25 | Loss:0.1022 | Train Accuracy:96.08%
Epoch 17/25 | Loss:0.1103 | Train Accuracy:95.85%
Epoch 18/25 | Loss:0.1050 | Train Accuracy:95.92%
Epoch 19/25 | Loss:0.0955 | Train Accuracy:96.34%
Epoch 20/25 | Loss:0.0893 | Train Accuracy:96.56%


In [89]:
model.eval()
test_correct=0
test_total=0

with torch.no_grad():
    for texts,labels in test_loader:
        texts=texts.to(device)
        labels = labels.to(device)

        predictions = model(texts)
        _, predicted = torch.max(predictions.data, 1)
        test_total += labels.size(0)
        test_correct += (predicted == labels).sum().item()

test_accuracy = 100 * test_correct / test_total
print(f"\nFinal Test Accuracy: {test_accuracy:.2f}%")


Final Test Accuracy: 81.45%
